#Cell 1

In [ ]:
# =============================================================================
# Phase 2 · Notebook 2 · Cleaning and Standardization (Silver Layer)
# =============================================================================
#
# Purpose:
#   Load all Bronze layer files, apply cleaning and standardization
#   transformations, and save clean data to the Silver folder.
#   No analytical logic enters this notebook — only cleaning.
#
# Silver layer rule: clean and standardize only.
#   No AHP weights, no ML, no feature engineering, no scoring.
#
# Transformations applied in this notebook:
#   1. Reproject all geometries from source CRS to EPSG:32632 UTM Zone 32N
#   2. Deduplicate OSM café locations using 5-meter spatial buffer threshold
#   3. Standardize geometry types (convert Polygons to Points where needed)
#   4. Parse and clean population CSV with correct number formatting
#   5. Apply binary filter — spatial join against Urban Atlas to flag and
#      exclude non-viable land use zones from the candidate cell set
#   6. Clip all layers to the study area boundary
#
# Inputs (all from Bronze folder):
#   - raw_study_area_boundary.geojson
#   - raw_cafes.geojson
#   - raw_transit_stops.geojson
#   - raw_road_network_nodes.geojson
#   - raw_road_network_edges.geojson
#   - raw_pois.geojson
#   - raw_urban_atlas.fgb
#   - raw_population.csv
#
# Outputs (all saved to Silver folder):
#   - silver_study_area.geojson
#   - silver_cafes.geojson
#   - silver_transit_stops.geojson
#   - silver_road_network_nodes.geojson
#   - silver_road_network_edges.geojson
#   - silver_pois.geojson
#   - silver_urban_atlas.geojson
#   - silver_population.geojson
#   - silver_cleaning_log.txt
#
# CRS throughout this notebook: EPSG:32632 UTM Zone 32N
# =============================================================================

#Cell 2

In [ ]:
# Install required libraries
!pip install osmnx -q
!pip install geopandas -q
!pip install shapely -q
!pip install pyproj -q
!pip install folium -q

   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 104.4/104.4 kB 6.9 MB/s eta 0:00:00


#Cell 3

In [ ]:
import os
import datetime
import warnings

# Scoped warning filters — suppress only known noisy third-party warnings.
# UserWarning (including warnings.warn() calls in Cells 9–10 for apportionment
# failures and intersection exceptions) must NOT be suppressed.
warnings.filterwarnings('ignore', category=FutureWarning)
warnings.filterwarnings('ignore', module='osmnx')

import geopandas as gpd
import pandas as pd
import numpy as np
import osmnx as ox
import folium

# Mount Google Drive
from google.colab import drive
drive.mount('/content/drive')

# Note: paths assume Google Drive mount; adjust PROJECT_ROOT for local execution
PROJECT_ROOT = '/content/drive/MyDrive/Thesis'
BRONZE_PATH  = os.path.join(PROJECT_ROOT, 'Bronze')
SILVER_PATH  = os.path.join(PROJECT_ROOT, 'Silver')

# Target CRS for all analytical work
TARGET_CRS = 'EPSG:32632'

print(f"Bronze path: {BRONZE_PATH}")
print(f"Silver path: {SILVER_PATH}")
print(f"Target CRS:  {TARGET_CRS}")
print(f"Notebook started: {datetime.datetime.now().strftime('%Y-%m-%d %H:%M')}")

Drive already mounted at /content/drive; to attempt to forcibly remount, call drive.mount("/content/drive", force_remount=True).
Bronze path: /content/drive/MyDrive/Thesis/Bronze
Silver path: /content/drive/MyDrive/Thesis/Silver
Target CRS:  EPSG:32632
Notebook started: 2026-04-26 10:07


#Cell 4

In [ ]:
print("Loading Bronze layer files...")
print()

# Study area boundary
study_area = gpd.read_file(
    os.path.join(BRONZE_PATH, 'raw_study_area_boundary.geojson')
)
print(f"Study area boundary:  {len(study_area)} feature, CRS: {study_area.crs}")

# Café locations
cafes = gpd.read_file(
    os.path.join(BRONZE_PATH, 'raw_cafes.geojson')
)
print(f"Cafés:                {len(cafes)} features, CRS: {cafes.crs}")

# Transit stops
transit = gpd.read_file(
    os.path.join(BRONZE_PATH, 'raw_transit_stops.geojson')
)
print(f"Transit stops:        {len(transit)} features, CRS: {transit.crs}")

# Guard: transit_type may be absent if all NB1 transit queries returned zero results
if 'transit_type' not in transit.columns:
    raise KeyError(
        "transit_type column missing from raw_transit_stops.geojson — "
        "re-run NB1 Cell 7 to ensure at least one transit type is present."
    )

# Road network nodes
road_nodes = gpd.read_file(
    os.path.join(BRONZE_PATH, 'raw_road_network_nodes.geojson')
)
print(f"Road nodes:           {len(road_nodes)} features, CRS: {road_nodes.crs}")

# Road network edges
road_edges = gpd.read_file(
    os.path.join(BRONZE_PATH, 'raw_road_network_edges.geojson')
)
print(f"Road edges:           {len(road_edges)} features, CRS: {road_edges.crs}")

# General POIs
pois = gpd.read_file(
    os.path.join(BRONZE_PATH, 'raw_pois.geojson')
)
print(f"General POIs:         {len(pois)} features, CRS: {pois.crs}")

# Urban Atlas — FlatGeobuf format; no GDAL size-limit configuration needed
urban_atlas = gpd.read_file(
    os.path.join(BRONZE_PATH, 'raw_urban_atlas.fgb')
)
print(f"Urban Atlas:          {len(urban_atlas)} features, CRS: {urban_atlas.crs}")

# Population CSV — only loaded if present; used only in the fallback branch
# (ISTAT shapefile takes priority and does not use this file)
population_csv_path = os.path.join(BRONZE_PATH, 'raw_population.csv')
if os.path.exists(population_csv_path):
    population_csv = pd.read_csv(population_csv_path, encoding='utf-8')
    print(f"Population CSV:       {len(population_csv)} rows")
else:
    population_csv = None
    print("Population CSV:       not found — will use ISTAT shapefile if available")

print()
print("All Bronze files loaded successfully")

Loading Bronze layer files...

Study area boundary:  1 feature, CRS: EPSG:4326
Cafés:                2014 features, CRS: EPSG:4326
Transit stops:        15136 features, CRS: EPSG:4326
Road nodes:           114046 features, CRS: EPSG:4326


/usr/local/lib/python3.12/dist-packages/geopandas/io/file.py:576: UserWarning: Could not parse column 'reversed' as JSON; leaving as string
  return pyogrio.read_dataframe(path_or_bytes, bbox=bbox, **kwargs)


Road edges:           337620 features, CRS: EPSG:4326
General POIs:         60271 features, CRS: EPSG:4326
Urban Atlas:          77413 features, CRS: EPSG:3035
Population CSV:       133 rows

All Bronze files loaded successfully


#Cell 5

In [ ]:
print("Standardizing geometry types...")
print()

def to_point_geometry(gdf, name):
    """
    Converts any non-Point geometry to its centroid.
    Returns a GeoDataFrame with only Point geometries.
    """
    # Separate Points from non-Points
    is_point = gdf.geometry.geom_type == 'Point'
    points     = gdf[is_point].copy()
    non_points = gdf[~is_point].copy()

    if len(non_points) > 0:
        # Convert non-Points to centroids
        non_points = non_points.copy()
        non_points['geometry'] = non_points.geometry.centroid
        result = pd.concat([points, non_points], ignore_index=True)
        print(f"  {name}: {len(non_points)} non-Point geometries "
              f"converted to centroids")
    else:
        result = points
        print(f"  {name}: all geometries already Points")

    return gpd.GeoDataFrame(result, geometry='geometry', crs=gdf.crs)

cafes   = to_point_geometry(cafes,   'Cafés')
transit = to_point_geometry(transit, 'Transit stops')
pois    = to_point_geometry(pois,    'POIs')

print()
print("Geometry standardization complete")

Standardizing geometry types...

  Cafés: 39 non-Point geometries converted to centroids
  Transit stops: 3291 non-Point geometries converted to centroids
  POIs: 17094 non-Point geometries converted to centroids

Geometry standardization complete


/tmp/ipykernel_2042/3071185652.py:17: UserWarning: Geometry is in a geographic CRS. Results from 'centroid' are likely incorrect. Use 'GeoSeries.to_crs()' to re-project geometries to a projected CRS before this operation.

  non_points['geometry'] = non_points.geometry.centroid
/tmp/ipykernel_2042/3071185652.py:17: UserWarning: Geometry is in a geographic CRS. Results from 'centroid' are likely incorrect. Use 'GeoSeries.to_crs()' to re-project geometries to a projected CRS before this operation.

  non_points['geometry'] = non_points.geometry.centroid
/tmp/ipykernel_2042/3071185652.py:17: UserWarning: Geometry is in a geographic CRS. Results from 'centroid' are likely incorrect. Use 'GeoSeries.to_crs()' to re-project geometries to a projected CRS before this operation.

  non_points['geometry'] = non_points.geometry.centroid


#Cell 6

In [ ]:
print(f"Reprojecting all layers to {TARGET_CRS}...")
print()

def reproject(gdf, name, target_crs=TARGET_CRS):
    original_crs = gdf.crs
    reprojected  = gdf.to_crs(target_crs)
    print(f"  {name}: {original_crs} → {target_crs}")
    return reprojected

study_area  = reproject(study_area,  'Study area boundary')
cafes       = reproject(cafes,       'Cafés')
transit     = reproject(transit,     'Transit stops')
road_nodes  = reproject(road_nodes,  'Road network nodes')
road_edges  = reproject(road_edges,  'Road network edges')
pois        = reproject(pois,        'General POIs')
urban_atlas = reproject(urban_atlas, 'Urban Atlas')

print()
print(f"All layers now in {TARGET_CRS}")
print(f"Distance unit: metres")

Reprojecting all layers to EPSG:32632...

  Study area boundary: EPSG:4326 → EPSG:32632
  Cafés: EPSG:4326 → EPSG:32632
  Transit stops: EPSG:4326 → EPSG:32632
  Road network nodes: EPSG:4326 → EPSG:32632
  Road network edges: EPSG:4326 → EPSG:32632
  General POIs: EPSG:4326 → EPSG:32632
  Urban Atlas: EPSG:3035 → EPSG:32632

All layers now in EPSG:32632
Distance unit: metres


#Cell 7

In [ ]:
print("Clipping all layers to study area boundary...")
print()

study_polygon = study_area.dissolve().geometry.iloc[0]
study_union = study_polygon  # alias reused in Cell 9 — avoids redundant dissolve
study_area_gdf = study_area.copy()  # keep GeoDataFrame form for gpd.clip

assert study_area_gdf.crs is not None and study_area_gdf.crs.to_epsg() == 32632, (
    f"study_area_gdf CRS mismatch: {study_area_gdf.crs} — "
    f"expected EPSG:32632. Re-run Cell 6 to reproject."
)

def clip_to_study_area(gdf, name, study_poly=study_polygon):
    """
    Clips point/polygon layers using intersects filter.
    Road edges and urban_atlas use gpd.clip() instead to truncate geometry
    at boundary.
    """
    before = len(gdf)
    clipped = gdf[gdf.geometry.intersects(study_poly)].copy()
    after = len(clipped)
    print(f"  {name}: {before} → {after} features "
          f"({before - after} removed outside study area)")
    return clipped.reset_index(drop=True)

cafes      = clip_to_study_area(cafes,      'Cafés')
transit    = clip_to_study_area(transit,    'Transit stops')
pois       = clip_to_study_area(pois,       'General POIs')

# gpd.clip() truncates polygons at the boundary; intersects filter would retain full polygons
urban_atlas_before = len(urban_atlas)
urban_atlas = gpd.clip(urban_atlas, study_area_gdf).reset_index(drop=True)
print(f"  Urban Atlas: {urban_atlas_before} → {len(urban_atlas)} features "
      f"({urban_atlas_before - len(urban_atlas)} removed/truncated at study boundary)")
print(f"  [Urban Atlas clipped with gpd.clip() — polygon geometries truncated at boundary]")

# gpd.clip() truncates edge geometries at boundary — ensures downstream midpoints stay in-bounds
road_edges_before = len(road_edges)
road_edges = gpd.clip(road_edges, study_area_gdf).reset_index(drop=True)
print(f"  Road network edges: {road_edges_before} → {len(road_edges)} features "
      f"({road_edges_before - len(road_edges)} removed/truncated at study boundary)")
print(f"  [Road edges clipped with gpd.clip() — edge geometries truncated at boundary]")

# Filter nodes to endpoints of clipped edges — keeps graph topology consistent
road_nodes_before = len(road_nodes)

if 'u' in road_edges.columns and 'v' in road_edges.columns:
    valid_node_ids = set(road_edges['u'].tolist() + road_edges['v'].tolist())

    assert 'osmid' in road_nodes.columns, (
        "osmid column missing from road_nodes — re-run NB1 Cell 8 to regenerate "
        "raw_road_network_nodes.geojson with osmid as a regular column."
    )

    road_nodes = road_nodes[
        road_nodes['osmid'].isin(valid_node_ids)
    ].copy().reset_index(drop=True)

    print(f"  Road network nodes: {road_nodes_before} → {len(road_nodes)} features "
          f"({road_nodes_before - len(road_nodes)} removed — not endpoint of any clipped edge)")
    print(f"  [Road nodes filtered to clipped-edge endpoints for topological consistency]")
else:
    # Fallback: u/v columns absent (unexpected schema) — use intersects as before
    road_nodes = clip_to_study_area(road_nodes, 'Road network nodes (fallback intersects)')
    print(f"  WARNING: road_edges missing 'u'/'v' columns — "
          f"road_nodes clipped by intersects() instead of edge endpoint filtering. "
          f"Verify graph topology before NB4.")

print()
print("Clipping complete")

Clipping all layers to study area boundary...

  Cafés: 2014 → 1734 features (280 removed outside study area)
  Transit stops: 15136 → 12741 features (2395 removed outside study area)
  General POIs: 60271 → 44552 features (15719 removed outside study area)
  Urban Atlas: 77413 → 6599 features (70814 removed/truncated at study boundary)
  [Urban Atlas clipped with gpd.clip() — polygon geometries truncated at boundary]
  Road network edges: 337620 → 258724 features (78896 removed/truncated at study boundary)
  [Road edges clipped with gpd.clip() — edge geometries truncated at boundary]
  Road network nodes: 114046 → 86043 features (28003 removed — not endpoint of any clipped edge)
  [Road nodes filtered to clipped-edge endpoints for topological consistency]

Clipping complete


#Cell 8

In [ ]:
# Deduplicate café and transit stop locations.
# Transit stops are often tagged under multiple OSM schemes (stop_position,
# bus_stop, platform) producing 2–3× duplicates that inflate transit_density in NB4.
# Method: buffer each point by half the threshold → STRtree + union-find →
# each connected component collapses to its highest-priority member. O(n log n).

from shapely.strtree import STRtree
from collections import defaultdict

DEDUP_THRESHOLD_M = 5  # metres (each point is buffered by half this)

def deduplicate_points(gdf, label):
    """
    Deduplicates a Point GeoDataFrame using STRtree + union-find.
    Returns the deduplicated GeoDataFrame (first member of each component kept).
    """
    gdf = gdf.reset_index(drop=True)
    n_before = len(gdf)

    buffered = [geom.buffer(DEDUP_THRESHOLD_M / 2.0) for geom in gdf.geometry]
    tree = STRtree(buffered)

    parent = list(range(len(gdf)))

    def find(x):
        while parent[x] != x:
            parent[x] = parent[parent[x]]
            x = parent[x]
        return x

    def union(a, b):
        ra, rb = find(a), find(b)
        if ra != rb:
            parent[rb] = ra

    for i, buf in enumerate(buffered):
        for j in tree.query(buf):
            if j != i:
                union(i, j)

    seen_roots = set()
    keep_idxs  = []
    for i in range(len(gdf)):
        root = find(i)
        if root not in seen_roots:
            seen_roots.add(root)
            keep_idxs.append(i)

    deduped = gdf.iloc[keep_idxs].reset_index(drop=True)
    print(f"  {label} before deduplication: {n_before}")
    print(f"  {label} after deduplication:  {len(deduped)}")
    print(f"  Duplicates removed:            {n_before - len(deduped)}")
    return deduped, n_before

print("Deduplicating café locations...")
cafes, n_cafes_before = deduplicate_points(cafes, 'Cafés')
print(f"  Deduplication threshold: {DEDUP_THRESHOLD_M} metres")
print(f"  Method: STRtree + union-find (O(n log n), order-independent)")
print()

# A single union-find pass builds components,then for each component we
# simultaneously:
#   1. select the representative geometry from the HIGHEST-PRIORITY member, AND
#   2. aggregate transit_type to the highest-priority type in that component.
# Priority order: metro > bus_tram > platform > bus_stop
print("Deduplicating transit stops (single unified pass)...")

TRANSIT_TYPE_PRIORITY = {'metro': 0, 'bus_tram': 1, 'platform': 2, 'bus_stop': 3}

transit = transit.reset_index(drop=True)
n_transit_before = len(transit)

# Build spatial index once
buffered_t = [geom.buffer(DEDUP_THRESHOLD_M / 2.0) for geom in transit.geometry]
tree_t     = STRtree(buffered_t)

parent_t = list(range(len(transit)))

def find_t(x):
    while parent_t[x] != x:
        parent_t[x] = parent_t[parent_t[x]]
        x = parent_t[x]
    return x

def union_t(a, b):
    ra, rb = find_t(a), find_t(b)
    if ra != rb:
        parent_t[rb] = ra

for i, buf in enumerate(buffered_t):
    for j in tree_t.query(buf):
        if j != i:
            union_t(i, j)

# Build component map: root → list of member indices
components_t = defaultdict(list)
for i in range(len(transit)):
    components_t[find_t(i)].append(i)

# For each component: keep geometry and transit_type of the highest-priority member
deduped_rows = []
for root, members in components_t.items():
    best_type = min(
        (transit.at[m, 'transit_type'] for m in members),
        key=lambda t: TRANSIT_TYPE_PRIORITY.get(t, 99)
    )
    # Representative geometry: member whose transit_type matches best_type;
    # on ties (multiple members of same best type) take the lowest index for
    # determinism.
    rep_idx = min(
        (m for m in members
         if transit.at[m, 'transit_type'] == best_type),
        default=min(members)
    )
    row = transit.iloc[rep_idx].copy()
    row['transit_type'] = best_type
    deduped_rows.append(row)

transit = gpd.GeoDataFrame(deduped_rows, geometry='geometry', crs=transit.crs)
transit = transit.reset_index(drop=True)

n_transit_after = len(transit)

# Guard: number of output rows must equal number of unique component roots
n_components = len(components_t)
assert n_transit_after == n_components, (
    f"Transit dedup assertion failed: {n_transit_after} rows != "
    f"{n_components} components. Component membership is inconsistent."
)

print(f"  Transit stops before deduplication: {n_transit_before}")
print(f"  Transit stops after deduplication:  {n_transit_after}")
print(f"  Duplicates removed:                 {n_transit_before - n_transit_after}")
print(f"  Deduplication threshold: {DEDUP_THRESHOLD_M} metres")
print(f"  Method: single STRtree + union-find pass; representative geometry from highest-priority member")
print(f"  Type priority: metro > bus_tram > platform > bus_stop")
print(f"  Assertion passed: output rows == component count ({n_components})")
print()
print("Deduplication complete")

Deduplicating café locations...
  Cafés before deduplication: 1734
  Cafés after deduplication:  1728
  Duplicates removed:            6
  Deduplication threshold: 5 metres
  Method: STRtree + union-find (O(n log n), order-independent)

Deduplicating transit stops (single unified pass)...
  Transit stops before deduplication: 12741
  Transit stops after deduplication:  6056
  Duplicates removed:                 6685
  Deduplication threshold: 5 metres
  Method: single STRtree + union-find pass; representative geometry from highest-priority member
  Type priority: metro > bus_tram > platform > bus_stop
  Assertion passed: output rows == component count (6056)

Deduplication complete


#Cell 9

In [ ]:
# =============================================================================
# ISTAT PATH (primary):
#   For census tracts that straddle the study boundary, POP21 is the
#   full-tract count but gpd.clip() would shrink the geometry. Naively
#   computing density from the clipped area inflates pop_density_per_km2
#   for boundary tracts. Fix: apportion POP21 proportionally before
#   clipping using intersection_area / original_tract_area.
#
# FALLBACK PATH:
#   Dati Lombardia 2019 CSV joined to OSM comune boundaries.
# =============================================================================

print("Cleaning and standardizing population data...")
print()

ISTAT_SHP_PATH = os.path.join(BRONZE_PATH, 'R03_21_WGS84.shp')
population_ready  = False   # set True at end of whichever branch succeeds
population_source = 'unavailable'          # safe default
population_gdf    = gpd.GeoDataFrame()    # safe default — prevents NameError

if os.path.exists(ISTAT_SHP_PATH):
    # ------------------------------------------------------------------
    # PRIMARY PATH — ISTAT 2021 census tracts (block-level granularity)
    # ------------------------------------------------------------------
    print("  ISTAT 2021 shapefile found — using as primary population source")
    census_tracts = gpd.read_file(ISTAT_SHP_PATH)
    census_tracts = census_tracts.to_crs(TARGET_CRS)

    census_tracts.columns = census_tracts.columns.str.strip().str.upper()
    if 'GEOMETRY' in census_tracts.columns:
        census_tracts.rename(columns={'GEOMETRY': 'geometry'}, inplace=True)
    census_tracts = census_tracts.set_geometry('geometry')

    print(f"  Census tracts loaded: {len(census_tracts)} features")

    if 'POP21' not in census_tracts.columns:
        raise KeyError(
            f"Expected 'POP21' column not found. "
            f"Available columns: {list(census_tracts.columns)}"
        )

    # Audit: flag tracts where POP21 is genuinely missing BEFORE fillna
    # This distinguishes real zero-population areas from NaN-coerced ones
    census_tracts['POP21'] = pd.to_numeric(
        census_tracts['POP21'], errors='coerce'
    )
    n_imputed = census_tracts['POP21'].isna().sum()
    census_tracts['pop21_is_imputed'] = census_tracts['POP21'].isna()
    census_tracts['POP21'] = census_tracts['POP21'].fillna(0)

    print(f"  Tracts with imputed POP21 (NaN→0): {n_imputed}")
    if n_imputed > 0:
        print(f"  NOTE: {n_imputed} tracts had NaN POP21 and were set to 0.")
        print(f"  These may include non-residential or institutional blocks.")
        print(f"  Column 'pop21_is_imputed' carried forward to silver_population.geojson.")

    # ------------------------------------------------------------------
    # AREAL APPORTIONMENT — must happen BEFORE gpd.clip()
    #
    # For each tract that intersects the study boundary, POP21 is the
    # full-tract headcount. We multiply it by
    #   intersection_area / original_tract_area
    # so that boundary-straddling tracts contribute only the population
    # share that falls inside the study area.
    # original_tract_area_km2 is stored for audit/verification.
    # ------------------------------------------------------------------

    # Record original (full-tract) area before any clipping
    census_tracts['original_tract_area_km2'] = (
        census_tracts.geometry.area / 1_000_000
    )

    # Pre-filter to tracts that actually intersect the study area BEFORE
    # running the intersection_area .apply() loop.
    # study_union is assigned once in Cell 7 (same object as study_polygon)
    # — no redundant dissolve here.
    census_tracts = census_tracts[
        census_tracts.geometry.intersects(study_union)
    ].copy()
    print(f"  Census tracts intersecting study area: {len(census_tracts)} "
          f"(pre-filtered before apportionment loop)")

    def intersection_area_km2(geom, study_geom=study_union):
        try:
            inter = geom.intersection(study_geom)
            return inter.area / 1_000_000
        except Exception as e:
            warnings.warn(
                f"Intersection failed for tract at "
                f"({geom.centroid.x:.1f}, {geom.centroid.y:.1f}): {e}"
            )
            return 0.0

    census_tracts['intersection_area_km2'] = (
        census_tracts.geometry.apply(intersection_area_km2)
    )

    census_tracts['apportion_ratio'] = np.where(
        census_tracts['original_tract_area_km2'] > 0,
        census_tracts['intersection_area_km2'] /
        census_tracts['original_tract_area_km2'],
        0.0
    ).clip(0.0, 1.0)

    census_tracts['pop_apportioned'] = (
        census_tracts['POP21'] * census_tracts['apportion_ratio']
    )

    # Audit: tracts where apportion_ratio=0 but POP21>0 indicate silent intersection failures
    n_zero_apportion_nonzero_pop = (
        (census_tracts['apportion_ratio'] == 0) &
        (census_tracts['POP21'] > 0)
    ).sum()
    if n_zero_apportion_nonzero_pop:
        print(
            f"  AUDIT WARNING: {n_zero_apportion_nonzero_pop} tract(s) have "
            f"apportion_ratio=0 but POP21>0 — possible silent intersection "
            f"failures. Review warnings above for tract coordinates."
        )
    else:
        print(f"  Apportionment audit: 0 tracts with apportion_ratio=0 and POP21>0 "
              f"(no silent intersection failures detected).")

    print(f"  Apportionment applied — total apportioned population: "
          f"{census_tracts['pop_apportioned'].sum():,.0f}")

    # Now clip to study area — geometry is truncated at boundary
    census_tracts = gpd.clip(census_tracts, study_area_gdf).reset_index(drop=True)
    print(f"  Census tracts after clip to study area: {len(census_tracts)}")

    # Drop gpd.clip() slivers — near-zero area tracts produce false-zero density values
    # Threshold: 0.0001 km² (100 m²), well below the smallest real Milan census tract
    n_before_sliver_drop = len(census_tracts)
    _clip_area_km2 = census_tracts.geometry.area / 1_000_000
    census_tracts = census_tracts[
        _clip_area_km2 > 1e-4
    ].copy().reset_index(drop=True)
    n_slivers_dropped = n_before_sliver_drop - len(census_tracts)
    print(f"  Sliver tracts dropped (area < 0.0001 km²): {n_slivers_dropped}")
    if n_slivers_dropped > 0:
        print(f"  NOTE: {n_slivers_dropped} sliver polygon(s) from gpd.clip() removed "
              f"before density computation to prevent false-zero pop_density values.")

    # Denominator is original tract area, not post-clip area
    # pop_density = pop_apportioned / original_area = (POP21 × ratio) / original_area
    census_tracts['tract_area_km2'] = census_tracts['original_tract_area_km2']

    census_tracts['pop_density_per_km2'] = (
        census_tracts['pop_apportioned'] /
        census_tracts['tract_area_km2'].replace(0, np.nan)
    ).fillna(0)

    print(f"  Total apportioned population (clipped study area): "
          f"{census_tracts['pop_apportioned'].sum():,.0f}")
    print(f"  Mean tract density: "
          f"{census_tracts['pop_density_per_km2'].mean():,.1f} residents/km²")

    population_source = 'ISTAT_2021_block'
    population_ready  = True

else:
    # ------------------------------------------------------------------
    # FALLBACK PATH — Dati Lombardia 2019 CSV + OSM comune boundaries
    # ------------------------------------------------------------------
    print("  ISTAT 2021 shapefile NOT found — falling back to Dati Lombardia 2019 CSV")
    print(f"  (Upload R03_21_WGS84.shp to {BRONZE_PATH} to use the primary source)")
    print()

    if population_csv is None:
        print("  WARNING: raw_population.csv also not found — population data unavailable")
        population_source = 'unavailable'
        comuni_boundaries = None
    else:
        name_col = 'Comune'
        pop_col  = 'Popolazione_residente__al_31-12-2019'
        area_col = 'Superficie_Kmq'

        # Clean population — remove comma thousands separators
        population_csv[pop_col] = (
            population_csv[pop_col]
            .astype(str)
            .str.replace(',', '', regex=False)
            .str.strip()
            .pipe(pd.to_numeric, errors='coerce')
        )

        # Clean surface area
        population_csv[area_col] = (
            population_csv[area_col]
            .astype(str)
            .str.replace(',', '', regex=False)
            .str.strip()
            .pipe(pd.to_numeric, errors='coerce')
        )

        # Compute population density
        population_csv['pop_density_per_km2'] = (
            population_csv[pop_col] / population_csv[area_col]
        )

        print(f"  Total population: {population_csv[pop_col].sum():,.0f}")
        print(f"  Number of comuni: {len(population_csv)}")
        print(f"  Mean density (pop/km²): "
              f"{population_csv['pop_density_per_km2'].mean():,.1f}")

        print()
        print("  Retrieving comune boundaries from OSM...")

        comuni_gdfs = []
        failed      = []

        for comune_name in population_csv[name_col]:
            try:
                gdf = ox.geocode_to_gdf(f"{comune_name}, Milano, Italy")
                gdf['comune_name'] = comune_name
                comuni_gdfs.append(gdf)
            except Exception:
                failed.append(comune_name)

        if comuni_gdfs:
            comuni_boundaries = pd.concat(comuni_gdfs, ignore_index=True)
            comuni_boundaries = comuni_boundaries.to_crs(TARGET_CRS)
            print(f"  Retrieved boundaries for {len(comuni_boundaries)} comuni")
            if failed:
                print(f"  Failed to retrieve {len(failed)} comuni: {failed[:5]}...")
        else:
            print("  Failed to retrieve comune boundaries")
            comuni_boundaries = None

        if comuni_boundaries is not None:

            def normalize_name(name):
                if pd.isna(name):
                    return ''
                name = str(name).upper().strip()
                replacements = {
                    'À':'A','È':'E','É':'E','Ì':'I',
                    'Ò':'O','Ù':'U','à':'a','è':'e',
                    'é':'e','ì':'i','ò':'o','ù':'u'
                }
                for accented, plain in replacements.items():
                    name = name.replace(accented, plain)
                return name

            population_csv['name_key'] = (
                population_csv[name_col].apply(normalize_name)
            )
            comuni_boundaries['name_key'] = (
                comuni_boundaries['comune_name'].apply(normalize_name)
            )

            # Merge population data onto comune boundaries
            population_gdf = comuni_boundaries.merge(
                population_csv[['name_key', pop_col, area_col]],
                on='name_key',
                how='left'
            )

            # Drop null geometries from left merge before area computation.
            population_gdf = population_gdf[
                population_gdf.geometry.notna()
            ].reset_index(drop=True)
            print(f"  Comuni with valid geometry: {len(population_gdf)}")

            # Clip to study area
            population_gdf = population_gdf[
                population_gdf.geometry.intersects(study_polygon)
            ].reset_index(drop=True)

            print(f"  Comuni within study area: {len(population_gdf)}")

            # Areal apportionment — mirrors the ISTAT primary path.
            # Boundary comuni contribute only their within-study population share.
            population_gdf['original_comune_area_km2'] = (
                population_gdf.geometry.area / 1_000_000
            )

            def fallback_intersection_area_km2(geom, study_geom=study_union):
                try:
                    inter = geom.intersection(study_geom)
                    return inter.area / 1_000_000
                except Exception as e:
                    warnings.warn(
                        f"Fallback intersection failed for comune at "
                        f"({geom.centroid.x:.1f}, {geom.centroid.y:.1f}): {e}"
                    )
                    return 0.0

            population_gdf['intersection_area_km2'] = (
                population_gdf.geometry.apply(fallback_intersection_area_km2)
            )

            population_gdf['apportion_ratio'] = np.where(
                population_gdf['original_comune_area_km2'] > 0,
                population_gdf['intersection_area_km2'] /
                population_gdf['original_comune_area_km2'],
                0.0
            ).clip(0.0, 1.0)

            population_gdf[pop_col] = pd.to_numeric(
                population_gdf[pop_col], errors='coerce'
            ).fillna(0)

            population_gdf['pop_apportioned'] = (
                population_gdf[pop_col] * population_gdf['apportion_ratio']
            )

            # Denominator is original comune area — same logic as ISTAT path
            # pop_density = pop_apportioned / original_area = (POP × ratio) / original_area
            population_gdf['tract_area_km2'] = population_gdf['original_comune_area_km2']

            population_gdf['pop_density_per_km2'] = (
                population_gdf['pop_apportioned'] /
                population_gdf['tract_area_km2'].replace(0, np.nan)
            ).fillna(0)

            print(f"  Apportionment applied — total apportioned population: "
                  f"{population_gdf['pop_apportioned'].sum():,.0f}")
            print(f"  Mean comune density: "
                  f"{population_gdf['pop_density_per_km2'].mean():,.1f} residents/km²")
            print()
            print("  Population GeoDataFrame sample:")
            print(population_gdf[['comune_name', pop_col,
                                   'pop_density_per_km2']].head())

            # Clip to boundary — intersects filter above retains full polygons for straddling comuni
            population_gdf = gpd.clip(
                population_gdf, study_area_gdf
            ).reset_index(drop=True)
            print(f"  Clipped to study boundary: {len(population_gdf)} comuni retained")

            # Drop gpd.clip() slivers — mirrors ISTAT path
            # Threshold: 0.0001 km² (100 m²)
            n_before_fb_sliver_drop = len(population_gdf)
            population_gdf['clipped_area_km2'] = (
                population_gdf.geometry.area / 1_000_000
            )
            population_gdf = population_gdf[
                population_gdf['clipped_area_km2'] > 1e-4
            ].copy().reset_index(drop=True)
            n_fb_slivers_dropped = n_before_fb_sliver_drop - len(population_gdf)
            print(f"  Fallback sliver comuni dropped (clipped area < 0.0001 km²): "
                  f"{n_fb_slivers_dropped}")
            if n_fb_slivers_dropped > 0:
                print(f"  NOTE: {n_fb_slivers_dropped} sliver polygon(s) from gpd.clip() "
                      f"removed to prevent near-zero pop_density values in NB4.")

            population_source = 'DatiLombardia_2019_comune'
            population_ready  = True
        else:
            # comuni_boundaries retrieval failed — source string must NOT be set
            # to a misleading value; distinguish "CSV absent" from "CSV found but
            # OSM geocoding failed" so the Silver log is not falsely 'unavailable'
            population_source = 'DatiLombardia_2019_comune_boundary_fetch_failed'
            population_ready  = False   # explicitly set — OSM geocoding failed for all comuni
            print()
            print("*** BLOCKING WARNING ***")
            print("  silver_population.geojson will NOT be saved.")
            print("  Cause: fallback OSM geocoding failed for all comuni.")
            print("  Actions:")
            print("    1. Check network access (OSM geocoding requires outbound HTTP).")
            print("    2. Or supply the primary source: upload R03_21_WGS84.shp to Bronze")
            print("       and re-run NB2 Cell 9.")

print()
print(f"  Population source recorded: {population_source}")
print(f"  population_ready: {population_ready}")

Cleaning and standardizing population data...

  ISTAT 2021 shapefile found — using as primary population source
  Census tracts loaded: 99886 features
  Tracts with imputed POP21 (NaN→0): 0
  Census tracts intersecting study area: 7333 (pre-filtered before apportionment loop)
  Apportionment audit: 0 tracts with apportion_ratio=0 and POP21>0 (no silent intersection failures detected).
  Apportionment applied — total apportioned population: 1,350,449
  Census tracts after clip to study area: 7333
  Sliver tracts dropped (area < 0.0001 km²): 37
  NOTE: 37 sliver polygon(s) from gpd.clip() removed before density computation to prevent false-zero pop_density values.
  Total apportioned population (clipped study area): 1,350,440
  Mean tract density: 26,834.1 residents/km²

  Population source recorded: ISTAT_2021_block
  population_ready: True


#Cell 10

In [ ]:
# =============================================================================
# Cell 10 — Apply the binary filter using Urban Atlas land use classes
# Any H3 cell whose centroid falls within a non-viable land use zone
# is excluded from the candidate location set entirely
#
# Non-viable classes for café site selection:
#   12100 — Industrial, commercial, public, military units
#   12210 — Fast transit roads
#   12220 — Other roads
#   12230 — Railways
#   12400 — Airports
#   13100 — Mineral extraction and dump sites
#   13300 — Construction sites
#   13400 — Land without current use
#   14110 — Green urban areas (public)
#   14120 — Green urban areas (private)
#   14130 — Green urban areas (unknown)
#   14200 — Sports and leisure facilities
#   21000 — Arable land
#   22000 — Permanent crops
#   23000 — Pastures
#   24000 — Complex cultivation patterns
#   31000 — Forests
#   32000 — Herbaceous vegetation
#   33000 — Open spaces
#   40000 — Wetlands
#   50000 — Water
#
# Viable classes (urban fabric — cafés can open here):
#   11100 — Continuous urban fabric
#   11210 — Discontinuous dense urban fabric
#   11220 — Discontinuous medium density urban fabric
#   11230 — Discontinuous low density urban fabric
#   11240 — Discontinuous very low density urban fabric
#   11300 — Isolated structures
# =============================================================================

print("Applying binary land use filter from Urban Atlas...")
print()
print(f"  code_2021 dtype: {urban_atlas['code_2021'].dtype}")
print(f"  Sample values:   {urban_atlas['code_2021'].unique()[:10]}")
print()

# Define viable land use codes
VIABLE_CODES = {11100, 11210, 11220, 11230, 11240, 11300}

# Cast code column to integer to ensure consistent comparison
urban_atlas['code_2021'] = (
    pd.to_numeric(urban_atlas['code_2021'], errors='coerce')
    .astype(float)
)

urban_atlas['is_viable'] = (
    urban_atlas['code_2021'].isin(VIABLE_CODES)
)

viable_zones     = urban_atlas[urban_atlas['is_viable']].copy()
non_viable_zones = urban_atlas[~urban_atlas['is_viable']].copy()

print(f"  code_2021 dtype after cast: {urban_atlas['code_2021'].dtype}")
print(f"  Viable urban fabric polygons:     {len(viable_zones)}")
print(f"  Non-viable land use polygons:     {len(non_viable_zones)}")

viable_union = None
viable_mask  = gpd.GeoDataFrame()   # empty GDF — safe default prevents NameError

if len(viable_zones) == 0:
    print()
    print("  WARNING: No viable zones found.")
    print("  Unique codes in dataset:")
    print(f"  {sorted(urban_atlas['code_2021'].dropna().unique().tolist())}")
    print()
    print("  Check whether the codes above match VIABLE_CODES and")
    print("  adjust VIABLE_CODES if needed before re-running.")
    print("  viable_union is None — Cell 12 log will report N/A for viable zone area.")
    print("  viable_mask is empty GeoDataFrame — Cell 11 save will be skipped.")
else:
    viable_union = viable_zones.dissolve().geometry.iloc[0]
    viable_mask = gpd.GeoDataFrame(
        {'viable': [True]},
        geometry=[viable_union],
        crs=TARGET_CRS
    )
    print()
    print(f"  Viable zone area: {viable_union.area / 1_000_000:.2f} km²")
    print()
    print("Binary filter applied successfully")

Applying binary land use filter from Urban Atlas...

  code_2021 dtype: object
  Sample values:   ['12230' '14200' '50000' '12100' '21000' '11230' '11220' '13400' '11210'
 '14110']

  code_2021 dtype after cast: float64
  Viable urban fabric polygons:     4395
  Non-viable land use polygons:     2204

  Viable zone area: 63.17 km²

Binary filter applied successfully


#Cell 11

In [ ]:
# =============================================================================
# GeoJSON RFC 7946 mandates WGS84 coordinates. All layers are reprojected
# to EPSG:4326 before writing so that any downstream tool (Leaflet, QGIS
# default open, web maps) that ignores embedded CRS metadata still places
# features correctly. The working CRS (EPSG:32632) is preserved in memory
# for any further operations within this notebook session.
# =============================================================================

print("Saving Silver layer outputs...")
print()

def save_silver(gdf, filename, description):
    assert gdf.crs is not None, (
        f"save_silver({filename}): GeoDataFrame has no CRS — set CRS before saving."
    )
    path = os.path.join(SILVER_PATH, filename)
    # Reproject to WGS84 for GeoJSON compliance (RFC 7946)
    gdf.to_crs('EPSG:4326').to_file(path, driver='GeoJSON')
    print(f"  [{description}] saved: {filename} ({len(gdf)} features, reprojected to WGS84)")
    return path

save_silver(study_area,     'silver_study_area.geojson',
            'Study area boundary')
save_silver(cafes,          'silver_cafes.geojson',
            'Cafés (deduplicated)')
save_silver(transit,        'silver_transit_stops.geojson',
            'Transit stops (deduplicated)')
save_silver(road_nodes,     'silver_road_network_nodes.geojson',
            'Road network nodes')
save_silver(road_edges,     'silver_road_network_edges.geojson',
            'Road network edges')
save_silver(pois,           'silver_pois.geojson',
            'General POIs')
save_silver(urban_atlas,    'silver_urban_atlas.geojson',
            'Urban Atlas (with viability flag)')

if len(viable_mask) > 0:
    save_silver(viable_mask, 'silver_viable_mask.geojson', 'Viable land use mask')
else:
    print("  [Viable land use mask] SKIPPED — viable_mask is empty "
          "(no viable Urban Atlas zones found). "
          "Resolve VIABLE_CODES in Cell 10 before proceeding to NB3.")

# Save population GeoDataFrame using the population_ready flag
# set at the end of whichever branch in Cell 9 succeeded.
if population_ready and len(population_gdf) > 0:
    save_silver(population_gdf, 'silver_population.geojson',
                'Population (census tract level)')
else:
    print("  [Population] skipped — population_ready=False or empty GeoDataFrame")

print()
print(f"All Silver files saved to: {SILVER_PATH}")
print(f"All GeoJSON files written in WGS84 (EPSG:4326) per RFC 7946.")
print(f"In-memory GeoDataFrames remain in {TARGET_CRS} for any further session use.")

Saving Silver layer outputs...

  [Study area boundary] saved: silver_study_area.geojson (1 features, reprojected to WGS84)
  [Cafés (deduplicated)] saved: silver_cafes.geojson (1728 features, reprojected to WGS84)
  [Transit stops (deduplicated)] saved: silver_transit_stops.geojson (6056 features, reprojected to WGS84)
  [Road network nodes] saved: silver_road_network_nodes.geojson (86043 features, reprojected to WGS84)
  [Road network edges] saved: silver_road_network_edges.geojson (258724 features, reprojected to WGS84)
  [General POIs] saved: silver_pois.geojson (44552 features, reprojected to WGS84)
  [Urban Atlas (with viability flag)] saved: silver_urban_atlas.geojson (6599 features, reprojected to WGS84)
  [Viable land use mask] saved: silver_viable_mask.geojson (1 features, reprojected to WGS84)
  [Population] skipped — population_ready=False or empty GeoDataFrame

All Silver files saved to: /content/drive/MyDrive/Thesis/Silver
All GeoJSON files written in WGS84 (EPSG:4326) pe

#Cell 12

In [ ]:
# Write cleaning log — audit trail for every transformation applied in this notebook
log_lines = [
    f"Thesis Phase 2 — Silver Layer Cleaning Log",
    f"==========================================",
    f"Notebook run date: "
    f"{datetime.datetime.now().strftime('%Y-%m-%d %H:%M')}",
    f"Target CRS: {TARGET_CRS}",
    f"",
    f"Transformations applied:",
    f"",
    f"1. Geometry standardization",
    f"   Non-Point café and POI geometries converted to centroids",
    f"",
    f"2. Reprojection",
    f"   All layers reprojected from source CRS to EPSG:32632",
    f"",
    f"3. Clipping",
    f"   Point layers clipped to study area boundary (intersects filter)",
    f"   Urban Atlas polygons clipped with gpd.clip() — truncated at boundary",
    f"   Road edges clipped with gpd.clip() — truncated at boundary",
    f"",
    f"4. Café deduplication",
    f"   Threshold: {DEDUP_THRESHOLD_M} metres",
    f"   Method:    STRtree + union-find (O(n log n), order-independent)",
    f"   Cafés before: {n_cafes_before}",
    f"   Cafés after:  {len(cafes)}",
    f"",
    f"   Transit stop deduplication",
    f"   Threshold: {DEDUP_THRESHOLD_M} metres",
    f"   Method:    single unified STRtree + union-find pass; priority: metro > bus_tram > platform > bus_stop",
    f"   Transit stops before: {n_transit_before}",
    f"   Transit stops after:  {n_transit_after}",
    f"",
    f"5. Population data",
    f"   Source: {population_source}",
    f"   {'ISTAT 2021 census tracts loaded, reprojected, clipped; tract_area_km2 and pop_density_per_km2 computed from POP21' if population_source == 'ISTAT_2021_block' else 'Comma thousands separators removed from population column; population density computed (residents per km²); population CSV joined to OSM comune boundaries'}",
    f"",
    f"6. Binary land use filter",
    f"   Source: Urban Atlas 2021",
    f"   Viable codes: {sorted(VIABLE_CODES)}",
    f"   Viable zone area: "
    f"{f'{viable_union.area / 1_000_000:.2f} km²' if viable_union is not None else 'N/A — no viable zones found'}",
    f"",
    f"Silver outputs:",
    f"   silver_study_area.geojson",
    f"   silver_cafes.geojson",
    f"   silver_transit_stops.geojson",
    f"   silver_road_network_nodes.geojson",
    f"   silver_road_network_edges.geojson",
    f"   silver_pois.geojson",
    f"   silver_urban_atlas.geojson",
    f"   silver_viable_mask.geojson",
    f"   silver_population.geojson",
]

log_path = os.path.join(SILVER_PATH, 'silver_cleaning_log.txt')
with open(log_path, 'w') as f:
    f.write('\n'.join(log_lines))

print('\n'.join(log_lines))
print(f"\nLog saved to: {log_path}")

Thesis Phase 2 — Silver Layer Cleaning Log
Notebook run date: 2026-04-26 10:11
Target CRS: EPSG:32632

Transformations applied:

1. Geometry standardization
   Non-Point café and POI geometries converted to centroids

2. Reprojection
   All layers reprojected from source CRS to EPSG:32632

3. Clipping
   Point layers clipped to study area boundary (intersects filter)
   Urban Atlas polygons clipped with gpd.clip() — truncated at boundary
   Road edges clipped with gpd.clip() — truncated at boundary

4. Café deduplication
   Threshold: 5 metres
   Method:    STRtree + union-find (O(n log n), order-independent)
   Cafés before: 1734
   Cafés after:  1728

   Transit stop deduplication
   Threshold: 5 metres
   Method:    single unified STRtree + union-find pass; priority: metro > bus_tram > platform > bus_stop
   Transit stops before: 12741
   Transit stops after:  6056

5. Population data
   Source: ISTAT_2021_block
   ISTAT 2021 census tracts loaded, reprojected, clipped; tract_area_km

#Cell 13

In [ ]:
m = folium.Map(
    location=[45.4642, 9.1900],
    zoom_start=12,
    tiles='CartoDB positron'
)

folium.GeoJson(
    study_area.to_crs('EPSG:4326').__geo_interface__,
    name='Study area',
    style_function=lambda x: {
        'fillColor': 'none',
        'color': '#333333',
        'weight': 2
    }
).add_to(m)

if len(viable_mask) > 0:
    folium.GeoJson(
        viable_mask.to_crs('EPSG:4326').__geo_interface__,
        name='Viable zones',
        style_function=lambda x: {
            'fillColor': '#1D9E75',
            'color': '#0F6E56',
            'weight': 0.5,
            'fillOpacity': 0.3
        }
    ).add_to(m)

cafe_sample = cafes.to_crs('EPSG:4326').head(500)
for _, row in cafe_sample.iterrows():
    if row.geometry is not None:
        folium.CircleMarker(
            location=[row.geometry.y, row.geometry.x],
            radius=3,
            color='#E8593C',
            fill=True,
            fill_opacity=0.8
        ).add_to(m)

folium.LayerControl().add_to(m)

print("Green  = viable land use zones (café locations possible)")
print("Red    = café locations after deduplication")
print("Border = study area boundary")
m

Green  = viable land use zones (café locations possible)
Red    = café locations after deduplication
Border = study area boundary


#Cell 14

In [ ]:
# Final summary — verify all Silver layer outputs are present before
# moving to Notebook 3

print("=" * 60)
print("NOTEBOOK 2 COMPLETE — Silver Layer Summary")
print("=" * 60)

expected_files = [
    'silver_study_area.geojson',
    'silver_cafes.geojson',
    'silver_transit_stops.geojson',
    'silver_road_network_nodes.geojson',
    'silver_road_network_edges.geojson',
    'silver_pois.geojson',
    'silver_urban_atlas.geojson',
    'silver_viable_mask.geojson',
    'silver_population.geojson',
    'silver_cleaning_log.txt'
]

# Read population_source from the Silver log for cause-specific messaging.
# The log is written by Cell 12 and is authoritative; reading it here avoids
# depending on in-memory state that may be stale if cells are re-run out of order.
_log_population_source = population_source  # in-memory fallback
_log_path = os.path.join(SILVER_PATH, 'silver_cleaning_log.txt')
if os.path.exists(_log_path):
    with open(_log_path, 'r') as _f:
        for _line in _f:
            if _line.strip().startswith('Source:'):
                _log_population_source = _line.strip().split('Source:', 1)[1].strip()
                break

def _population_blocking_message(source):
    """Return a cause-specific BLOCKING hint for silver_population.geojson."""
    if source == 'unavailable':
        return (
            "*** BLOCKING — both R03_21_WGS84.shp and raw_population.csv are absent. "
            "Upload at least one to Bronze and re-run NB2 Cell 9 ***"
        )
    elif source == 'DatiLombardia_2019_comune_boundary_fetch_failed':
        return (
            "*** BLOCKING — fallback OSM geocoding failed for all comuni. "
            "Check network access, or upload R03_21_WGS84.shp to Bronze and re-run NB2 Cell 9 ***"
        )
    else:
        # Should not reach here if population.geojson is missing but source looks valid
        return (
            f"*** BLOCKING — population_source='{source}' but file not saved. "
            "Re-run NB2 Cell 9 ***"
        )

all_present = True
CONDITIONAL_FILES = {'silver_viable_mask.geojson'}

for filename in expected_files:
    filepath = os.path.join(SILVER_PATH, filename)
    status   = "OK" if os.path.exists(filepath) else "MISSING"
    if status == "MISSING":
        if filename in CONDITIONAL_FILES:
            print(f"  [SKIPPED] {filename}  (no viable Urban Atlas zones found — expected)")
        else:
            all_present = False
            if filename == 'silver_population.geojson':
                print(f"  [{status}] {filename}  {_population_blocking_message(_log_population_source)}")
            else:
                print(f"  [{status}] {filename}")
    else:
        print(f"  [{status}] {filename}")

print()
if all_present:
    print("All Silver files present. Ready to proceed to Notebook 3.")
    print("Next: H3 grid generation and spatial backbone construction.")
else:
    print("Some files are missing. Review the cells above before proceeding.")

NOTEBOOK 2 COMPLETE — Silver Layer Summary
  [OK] silver_study_area.geojson
  [OK] silver_cafes.geojson
  [OK] silver_transit_stops.geojson
  [OK] silver_road_network_nodes.geojson
  [OK] silver_road_network_edges.geojson
  [OK] silver_pois.geojson
  [OK] silver_urban_atlas.geojson
  [OK] silver_viable_mask.geojson
  [OK] silver_population.geojson
  [OK] silver_cleaning_log.txt

All Silver files present. Ready to proceed to Notebook 3.
Next: H3 grid generation and spatial backbone construction.
